# Import

In [1]:
import pandas as pd
import json

from curation_tools.curation_tools import (
    CuratedDataset,
    ObsSchema,
    VarSchema,
    Experiment,
    download_file,
    upload_parquet_to_bq
)

import logging
logging.basicConfig(
    level=logging.INFO,
    format="%(asctime)s %(levelname)s %(name)s: %(message)s",
    handlers=[
        logging.FileHandler("curation.log"),
        logging.StreamHandler(),  # keep console output too
    ],
    force=True,
)
# show all columns
pd.set_option('display.max_columns', None)
pd.options.mode.string_storage = "python"


/nfs/production/mfreeberg/perturb-seq/aleks/PerturbationCatalogue/.venv/lib/python3.12/site-packages/pandera/_pandas_deprecated.py:157: FutureWarning: Importing pandas-specific classes and functions from the
top-level pandera module will be **removed in a future version of pandera**.
If you're using pandera to validate pandas objects, we highly recommend updating
your import:

```
# old import
import pandera as pa

# new import
import pandera.pandas as pa
```

If you're using pandera to validate objects from other compatible libraries
like pyspark or polars, see the supported libraries section of the documentation
for more information on how to import pandera:

https://pandera.readthedocs.io/en/stable/supported_libraries.html

To disable this warning, set the environment variable:

```
export DISABLE_PANDERA_IMPORT_WARNING=True
```

  warnings.warn(_future_warning, FutureWarning)


# Download data

In [2]:
# !aws s3 cp --no-sign-request s3://genome-scale-tcell-perturb-seq/marson2025_data/D1_Rest.assigned_guide.h5ad ../non_curated/h5ad/zhu_2025_D1_rest_cl.h5ad
# !mv /content/PerturbationCatalogue/data_exploration/Perturbseq/non_curated/h5ad/D1_Rest.assigned_guide.h5ad /content/PerturbationCatalogue/data_exploration/Perturbseq/non_curated/h5ad/zhu_2025_pseudobulk.h5ad

# Initialise the dataset object

In [3]:
noncurated_path = '../non_curated/h5ad/zhu_2025_D4_rest_cl.h5ad'
cur_data = CuratedDataset(
    obs_schema=ObsSchema,
    var_schema=VarSchema,
    exp_metadata_schema=Experiment,
    noncurated_path=noncurated_path
)

cur_data.load_data()

Loading data from ../non_curated/h5ad/zhu_2025_D4_rest_cl.h5ad


In [4]:
cur_data.adata.obs

,lane_id,n_genes_by_counts,total_counts,pct_counts_mt,top_guide_UMI_counts,guide_id,perturbed_gene_name,perturbed_gene_id,guide_type,PuroR,guide_group,low_quality
AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L13,3108,6484.0,0.200494,25.0,MT1F-1,MT1F,ENSG00000198417,targeting,2.621869,targeting single sgRNA,False
AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L13,6986,37902.0,0.477547,1318.0,ZNF784-1,ZNF784,ENSG00000179922,targeting,1.852205,targeting single sgRNA,False
AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L13,3634,7963.0,0.389301,5.0,PFDN1-2,PFDN1,ENSG00000113068,targeting,1.434438,targeting single sgRNA,False
AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L13,5032,14945.0,1.124122,NaN,NaN,NaN,NaN,NaN,0.000000,no sgRNA,False
AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L13,5069,13334.0,0.427479,NaN,NaN,NaN,NaN,NaN,0.888736,no sgRNA,False
...,...,...,...,...,...,...,...,...,...,...,...,...
TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L12,2522,4652.0,0.795357,3.0,NTC-902,NTC,NTC,non-targeting,2.510375,targeting single sgRNA,False
TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L12,5591,19144.0,1.123067,115.0,SYNE2-2,SYNE2,ENSG00000054654,targeting,1.594534,targeting single sgRNA,False
TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L12,3462,7138.0,0.448305,78.0,GOLGA8B-2,GOLGA8B,ENSG00000215252,targeting,2.532308,targeting single sgRNA,False
TTTGTGAGTTGTGACTAGCTGTGA-1_CD4i_R2L12_CD4i_R2_D4_Rest_CD4i_R2_Ultima,CD4i_R2L12,4936,14650.0,1.180887,40.0,RPH3AL-1,RPH3AL,ENSG00000181031,targeting,1.725858,targeting single sgRNA,False


In [5]:
cur_data.adata.var

,gene_ids,feature_types,genome,gene_name,mt
CUSTOM001_PuroR,CUSTOM001_PuroR,Gene Expression,GRCh38,PuroR,False
ENSG00000000003,ENSG00000000003,Gene Expression,GRCh38,TSPAN6,False
ENSG00000000005,ENSG00000000005,Gene Expression,GRCh38,TNMD,False
ENSG00000000419,ENSG00000000419,Gene Expression,GRCh38,DPM1,False
ENSG00000000457,ENSG00000000457,Gene Expression,GRCh38,SCYL3,False
...,...,...,...,...,...
ENSG00000291110,ENSG00000291110,Gene Expression,GRCh38,TRIM16L,False
ENSG00000291122,ENSG00000291122,Gene Expression,GRCh38,CASTOR3P,False
ENSG00000291135,ENSG00000291135,Gene Expression,GRCh38,FCGR1BP,False
ENSG00000291145,ENSG00000291145,Gene Expression,GRCh38,PPP5D1P,False


# OBS slot curation

### Since for multi-guide perturbations the identities of said guides are unknown, we are filtering out these cells.

In [6]:
print(f"Number of cells before filtering: {cur_data.adata.n_obs}")
cur_data.adata = cur_data.adata[cur_data.adata.obs['guide_id'] != 'multi_sgRNA']
print(f"Number of cells after filtering: {cur_data.adata.n_obs}")

Number of cells before filtering: 2693903
Number of cells after filtering: 2154290


### Add `index` as `perturbation_name`

In [7]:
cur_data.adata.obs['cell_barcode'] = cur_data.adata.obs.index.str.split('_').str[0]
cur_data.adata.obs['perturbation_name'] = cur_data.adata.obs['cell_barcode'] +'_'+cur_data.adata.obs['lane_id'].astype(str)

/tmp/ipykernel_171365/2231587657.py:1: ImplicitModificationWarning: Trying to modify attribute `.obs` of view, initializing view as actual.
  cur_data.adata.obs['cell_barcode'] = cur_data.adata.obs.index.str.split('_').str[0]


### Show unique perturbations

In [8]:
cur_data.show_unique(slot = 'obs', column = 'perturbation_name')

Unique values in adata.obs.perturbation_name: 2154290
--------------------------------------------------
{'AAACAAGCAAACAAGAAGCTGTGA-1_CD4i_R2L22',
 'AAACAAGCAAACAAGAATCCCAAC-1_CD4i_R2L08',
 'AAACAAGCAAACAATCAAGTAGAG-1_CD4i_R2L17',
 'AAACAAGCAAACAATCAGCTGTGA-1_CD4i_R2L17',
 'AAACAAGCAAACAATCAGCTGTGA-1_CD4i_R2L19',
 'AAACAAGCAAACAATCATCCCAAC-1_CD4i_R2L04',
 'AAACAAGCAAACAATCATCCCAAC-1_CD4i_R2L19',
 'AAACAAGCAAACAATCATCCCAAC-1_CD4i_R2L22',
 'AAACAAGCAAACACGCAGCTGTGA-1_CD4i_R2L11',
 'AAACAAGCAAACCCAAAAGTAGAG-1_CD4i_R2L23',
 'AAACAAGCAAACCCAAACAGACCT-1_CD4i_R2L19',
 'AAACAAGCAAACCCAAATCCCAAC-1_CD4i_R2L23',
 'AAACAAGCAAACCGTAAAGTAGAG-1_CD4i_R2L15',
 'AAACAAGCAAACCGTAAAGTAGAG-1_CD4i_R2L22',
 'AAACAAGCAAACCGTAACAGACCT-1_CD4i_R2L15',
 'AAACAAGCAAACCTGAAGCTGTGA-1_CD4i_R2L09',
 'AAACAAGCAAACCTGAATCCCAAC-1_CD4i_R2L02',
 'AAACAAGCAAACGGGAAGCTGTGA-1_CD4i_R2L04',
 'AAACAAGCAAACGGGAAGCTGTGA-1_CD4i_R2L10',
 'AAACAAGCAAACGGGAATCCCAAC-1_CD4i_R2L10',
 'AAACAAGCAAACGGTCAAGTAGAG-1_CD4i_R2L22',
 'AAACAAGCAAA

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



'CAACCAACATCACTCGAAGTAGAG-1_CD4i_R2L24',
 'CAACCAACATCACTCGACAGACCT-1_CD4i_R2L19',
 'CAACCAACATCACTCGAGCTGTGA-1_CD4i_R2L13',
 'CAACCAACATCACTCGATCCCAAC-1_CD4i_R2L13',
 'CAACCAACATCACTCGATCCCAAC-1_CD4i_R2L19',
 'CAACCAACATCAGGACAAGTAGAG-1_CD4i_R2L15',
 'CAACCAACATCAGGACAAGTAGAG-1_CD4i_R2L18',
 'CAACCAACATCAGGACAGCTGTGA-1_CD4i_R2L02',
 'CAACCAACATCAGGACATCCCAAC-1_CD4i_R2L18',
 'CAACCAACATCAGGTAACAGACCT-1_CD4i_R2L01',
 'CAACCAACATCAGGTAACAGACCT-1_CD4i_R2L12',
 'CAACCAACATCAGGTAACAGACCT-1_CD4i_R2L16',
 'CAACCAACATCAGGTAATCCCAAC-1_CD4i_R2L11',
 'CAACCAACATCATAGGAAGTAGAG-1_CD4i_R2L12',
 'CAACCAACATCATCACACAGACCT-1_CD4i_R2L23',
 'CAACCAACATCATCACATCCCAAC-1_CD4i_R2L18',
 'CAACCAACATCATGCTAGCTGTGA-1_CD4i_R2L10',
 'CAACCAACATCCAAGAAAGTAGAG-1_CD4i_R2L10',
 'CAACCAACATCCAAGAAGCTGTGA-1_CD4i_R2L02',
 'CAACCAACATCCACCAACAGACCT-1_CD4i_R2L24',
 'CAACCAACATCCACCAATCCCAAC-1_CD4i_R2L07',
 'CAACCAACATCCCAATAAGTAGAG-1_CD4i_R2L10',
 'CAACCAACATCCCAATACAGACCT-1_CD4i_R2L10',
 'CAACCAACATCCCTCTAAGTAGAG-1_CD4i_R

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



,
 'GAGTAACTCCAAACGGATCCCAAC-1_CD4i_R2L15',
 'GAGTAACTCCAAAGACACAGACCT-1_CD4i_R2L07',
 'GAGTAACTCCAAAGACACAGACCT-1_CD4i_R2L14',
 'GAGTAACTCCAAAGACAGCTGTGA-1_CD4i_R2L24',
 'GAGTAACTCCAAAGACATCCCAAC-1_CD4i_R2L07',
 'GAGTAACTCCAAAGACATCCCAAC-1_CD4i_R2L14',
 'GAGTAACTCCAAAGGTAAGTAGAG-1_CD4i_R2L21',
 'GAGTAACTCCAAAGGTACAGACCT-1_CD4i_R2L20',
 'GAGTAACTCCAAAGGTAGCTGTGA-1_CD4i_R2L19',
 'GAGTAACTCCAAAGGTATCCCAAC-1_CD4i_R2L15',
 'GAGTAACTCCAAAGGTATCCCAAC-1_CD4i_R2L20',
 'GAGTAACTCCAAATAGAAGTAGAG-1_CD4i_R2L07',
 'GAGTAACTCCAAATAGAAGTAGAG-1_CD4i_R2L09',
 'GAGTAACTCCAAATAGATCCCAAC-1_CD4i_R2L09',
 'GAGTAACTCCAAATTCAAGTAGAG-1_CD4i_R2L01',
 'GAGTAACTCCAAATTCAAGTAGAG-1_CD4i_R2L09',
 'GAGTAACTCCAAATTCACAGACCT-1_CD4i_R2L06',
 'GAGTAACTCCAAATTCAGCTGTGA-1_CD4i_R2L09',
 'GAGTAACTCCAAATTCATCCCAAC-1_CD4i_R2L16',
 'GAGTAACTCCAAATTCATCCCAAC-1_CD4i_R2L23',
 'GAGTAACTCCAACAGGAAGTAGAG-1_CD4i_R2L16',
 'GAGTAACTCCAACAGGAAGTAGAG-1_CD4i_R2L21',
 'GAGTAACTCCAACAGGATCCCAAC-1_CD4i_R2L14',
 'GAGTAACTCCAACAGGATCCCAAC-1_CD4

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



'TACGTTAGTCATCCCTATCCCAAC-1_CD4i_R2L07',
 'TACGTTAGTCATCCCTATCCCAAC-1_CD4i_R2L10',
 'TACGTTAGTCATCCCTATCCCAAC-1_CD4i_R2L18',
 'TACGTTAGTCATCCCTATCCCAAC-1_CD4i_R2L24',
 'TACGTTAGTCATCCTCACAGACCT-1_CD4i_R2L08',
 'TACGTTAGTCATGAAGAAGTAGAG-1_CD4i_R2L08',
 'TACGTTAGTCATGAAGAAGTAGAG-1_CD4i_R2L15',
 'TACGTTAGTCATGAAGAAGTAGAG-1_CD4i_R2L22',
 'TACGTTAGTCATGAAGACAGACCT-1_CD4i_R2L07',
 'TACGTTAGTCATGAAGACAGACCT-1_CD4i_R2L11',
 'TACGTTAGTCATGAAGACAGACCT-1_CD4i_R2L22',
 'TACGTTAGTCATGAAGAGCTGTGA-1_CD4i_R2L15',
 'TACGTTAGTCATGAAGATCCCAAC-1_CD4i_R2L18',
 'TACGTTAGTCATGAAGATCCCAAC-1_CD4i_R2L22',
 'TACGTTAGTCATGCATAAGTAGAG-1_CD4i_R2L13',
 'TACGTTAGTCATGCATAAGTAGAG-1_CD4i_R2L24',
 'TACGTTAGTCATGCATACAGACCT-1_CD4i_R2L14',
 'TACGTTAGTCATGCATAGCTGTGA-1_CD4i_R2L14',
 'TACGTTAGTCATGCATATCCCAAC-1_CD4i_R2L18',
 'TACGTTAGTCATTACAAAGTAGAG-1_CD4i_R2L05',
 'TACGTTAGTCATTACAAAGTAGAG-1_CD4i_R2L14',
 'TACGTTAGTCATTACAAAGTAGAG-1_CD4i_R2L16',
 'TACGTTAGTCATTACAACAGACCT-1_CD4i_R2L07',
 'TACGTTAGTCATTACAAGCTGTGA-1_CD4i_R

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



### Add guide RNA information

In [9]:
# download the guide RNA spreadsheet
download_file(
    url="https://raw.githubusercontent.com/emdann/GWT_perturbseq_analysis_2025/refs/heads/master/metadata/suppl_tables/sgrna_library_metadata.suppl_table.csv",
    dest_path="../supplementary/zhu_2025_guide_info.csv"
)
# read in the guide RNA info csv
guide_info_df = pd.read_csv("../supplementary/zhu_2025_guide_info.csv")

guide_info_df = guide_info_df[['sgRNA', 'seq']]

guide_info_df['sgRNA'] = guide_info_df['sgRNA'].str.replace('1-Jun','JUN-1').str.replace('2-Jun','JUN-2')

guide_info_df = guide_info_df.rename(columns={'seq': 'guide_sequence', 'sgRNA':'guide_id'})

guide_info_df


File ../supplementary/zhu_2025_guide_info.csv already exists. Skipping download.


,guide_id,guide_sequence
0,ARMC5-1,CTGCCTCGCGCAGCTCGCGG
1,DDB1-1,GGAGTTCGCTGCGCGCTGTT
2,FNDC10-1,TGCCCGCTCCCCGCGATCCC
3,RORC-1,TCTGTGGGGCCCTGTCCATG
4,SLC35F6-1,GAACAGCTGGTACTTGGTCC
...,...,...
26499,NTC-988,TTTCAGGCTACGGGCGCGGG
26500,NTC-989,TTTCCCATGATCATTTAGTG
26501,NTC-990,TTTCGCCCAAGAGGCTTGGG
26502,NTC-991,TTTCGTGCCGATGTAACACA


In [10]:
print("Number of overlapping guides with cur_data:")
cur_data.adata.obs['guide_id'].isin(guide_info_df['guide_id'].to_list()).value_counts()

Number of overlapping guides with cur_data:


guide_id
True     1753668
False     400622
Name: count, dtype: int64

In [11]:
# merge cur_data.adata.obs with guide_info_df
cur_data.adata.obs = cur_data.adata.obs.merge(guide_info_df, on='guide_id', how='left')
# check that there are no missing guide sequences
print(f"Number of missing guide sequences: {cur_data.adata.obs['guide_sequence'].isna().sum()}")


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


Number of missing guide sequences: 400622


In [12]:
cur_data.adata.obs

,lane_id,n_genes_by_counts,total_counts,pct_counts_mt,top_guide_UMI_counts,guide_id,perturbed_gene_name,perturbed_gene_id,guide_type,PuroR,guide_group,low_quality,cell_barcode,perturbation_name,guide_sequence
0,CD4i_R2L13,3108,6484.0,0.200494,25.0,MT1F-1,MT1F,ENSG00000198417,targeting,2.621869,targeting single sgRNA,False,AAACAAGCAACAGAGGAAGTAGAG-1,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,TGGAAAGTCCAGTCTCTCCT
1,CD4i_R2L13,6986,37902.0,0.477547,1318.0,ZNF784-1,ZNF784,ENSG00000179922,targeting,1.852205,targeting single sgRNA,False,AAACAAGCAACAGAGGATCCCAAC-1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,TGGGATCGCGACTCCGGAGT
2,CD4i_R2L13,3634,7963.0,0.389301,5.0,PFDN1-2,PFDN1,ENSG00000113068,targeting,1.434438,targeting single sgRNA,False,AAACAAGCAACAGCACAAGTAGAG-1,AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13,CTTCAGCTCTAGATCCACGG
3,CD4i_R2L13,5032,14945.0,1.124122,NaN,NaN,NaN,NaN,NaN,0.000000,no sgRNA,False,AAACAAGCAACCTCGCATCCCAAC-1,AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13,NaN
4,CD4i_R2L13,5069,13334.0,0.427479,NaN,NaN,NaN,NaN,NaN,0.888736,no sgRNA,False,AAACAAGCAACGACTAATCCCAAC-1,AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2154285,CD4i_R2L12,2522,4652.0,0.795357,3.0,NTC-902,NTC,NTC,non-targeting,2.510375,targeting single sgRNA,False,TTTGTGAGTTGTCCAGAGCTGTGA-1,TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12,TAGTCCTTAGGGTGGGCTGA
2154286,CD4i_R2L12,5591,19144.0,1.123067,115.0,SYNE2-2,SYNE2,ENSG00000054654,targeting,1.594534,targeting single sgRNA,False,TTTGTGAGTTGTGACTAAGTAGAG-1,TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12,TCCAGAGAGCCAGGCAAGCG
2154287,CD4i_R2L12,3462,7138.0,0.448305,78.0,GOLGA8B-2,GOLGA8B,ENSG00000215252,targeting,2.532308,targeting single sgRNA,False,TTTGTGAGTTGTGACTACAGACCT-1,TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12,GCTTGAGAGCCCGCACGTAG
2154288,CD4i_R2L12,4936,14650.0,1.180887,40.0,RPH3AL-1,RPH3AL,ENSG00000181031,targeting,1.725858,targeting single sgRNA,False,TTTGTGAGTTGTGACTAGCTGTGA-1,TTTGTGAGTTGTGACTAGCTGTGA-1_CD4i_R2L12,CGGGTCACCCCCGACAACGG


In [13]:
# change perturbed_gene_id from categorical to string
cur_data.adata.obs['perturbed_gene_id'] = cur_data.adata.obs['perturbed_gene_id'].astype(str)
cur_data.adata.obs['perturbed_gene_name'] = cur_data.adata.obs['perturbed_gene_name'].astype(str)

cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_id'].isin(['NTC']), 'perturbed_gene_id'] = 'control_nontargeting'
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isin(['NTC']), 'perturbed_gene_name'] = 'control_nontargeting'

cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_id'].isna(), 'perturbed_gene_id'] = 'control_casonly'
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isna(), 'perturbed_gene_name'] = 'control_casonly'

### Standardise perturbation targets

In [14]:
cur_data.standardize_genes(
    slot='obs',
    input_column='perturbed_gene_id',
    input_column_type='ensembl_gene_id',
    multiple_entries=False,
    # remove_version=True,
    # version_sep='.'
)

Missing Ensembl IDs: ['AKAP2', 'ENSG00000148362', 'OCLM', 'ENSG00000255823', 'ENSG00000277796', 'LUZP6', 'ENSG00000203812', 'U2AF1L5', 'ENSG00000182230', 'SMIM11B', 'ENSG00000232196', 'SEPT6', 'SGK494', 'ENSG00000256618']; attempting to fetch latest IDs...
Fetched latest Ensembl IDs: {'ENSG00000148362': 'ENSG00000310560', 'ENSG00000255823': nan, 'ENSG00000277796': 'ENSG00000293545', 'ENSG00000203812': 'ENSG00000288825', 'ENSG00000182230': nan, 'ENSG00000232196': nan, 'ENSG00000256618': nan}
--------------------------------------------------
Successfully mapped 12417 out of 12417 Ensembl IDs.
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


In [15]:
cur_data.adata.obs

,guide_group,perturbed_gene_id,total_counts,top_guide_UMI_counts,pct_counts_mt,lane_id,cell_barcode,perturbation_name,perturbed_gene_name,n_genes_by_counts,PuroR,guide_type,guide_sequence,low_quality,guide_id,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index
index,,,,,,,,,,,,,,,,,,,,,
0,targeting single sgRNA,ENSG00000198417,6484.0,25.0,0.200494,CD4i_R2L13,AAACAAGCAACAGAGGAAGTAGAG-1,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,MT1F,3108,2.621869,targeting,TGGAAAGTCCAGTCTCTCCT,False,MT1F-1,ENSG00000198417,MT1F,protein_coding,chr16:56657640-56660698;1,16,0
1,targeting single sgRNA,ENSG00000179922,37902.0,1318.0,0.477547,CD4i_R2L13,AAACAAGCAACAGAGGATCCCAAC-1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,ZNF784,6986,1.852205,targeting,TGGGATCGCGACTCCGGAGT,False,ZNF784-1,ENSG00000179922,ZNF784,protein_coding,chr19:55620741-55624566;-1,19,1
2,targeting single sgRNA,ENSG00000113068,7963.0,5.0,0.389301,CD4i_R2L13,AAACAAGCAACAGCACAAGTAGAG-1,AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13,PFDN1,3634,1.434438,targeting,CTTCAGCTCTAGATCCACGG,False,PFDN1-2,ENSG00000113068,PFDN1,protein_coding,chr5:140245035-140303113;-1,5,2
3,no sgRNA,nan,14945.0,NaN,1.124122,CD4i_R2L13,AAACAAGCAACCTCGCATCCCAAC-1,AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13,nan,5032,0.000000,NaN,NaN,False,NaN,nan,NaN,NaN,NaN,NaN,3
4,no sgRNA,nan,13334.0,NaN,0.427479,CD4i_R2L13,AAACAAGCAACGACTAATCCCAAC-1,AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13,nan,5069,0.888736,NaN,NaN,False,NaN,nan,NaN,NaN,NaN,NaN,4
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2154285,targeting single sgRNA,control_nontargeting,4652.0,3.0,0.795357,CD4i_R2L12,TTTGTGAGTTGTCCAGAGCTGTGA-1,TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12,control_nontargeting,2522,2.510375,non-targeting,TAGTCCTTAGGGTGGGCTGA,False,NTC-902,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,2154285
2154286,targeting single sgRNA,ENSG00000054654,19144.0,115.0,1.123067,CD4i_R2L12,TTTGTGAGTTGTGACTAAGTAGAG-1,TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12,SYNE2,5591,1.594534,targeting,TCCAGAGAGCCAGGCAAGCG,False,SYNE2-2,ENSG00000054654,SYNE2,protein_coding,chr14:63761899-64226433;1,14,2154286
2154287,targeting single sgRNA,ENSG00000215252,7138.0,78.0,0.448305,CD4i_R2L12,TTTGTGAGTTGTGACTACAGACCT-1,TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12,GOLGA8B,3462,2.532308,targeting,GCTTGAGAGCCCGCACGTAG,False,GOLGA8B-2,ENSG00000215252,GOLGA8B,protein_coding,chr15:34525095-34588503;-1,15,2154287


# Manually replace some genes

In [16]:
# define genes to replace in the cur_data.adata.obs
genes_to_replace = cur_data.adata.obs[cur_data.adata.obs['perturbed_target_symbol'].isna()]['perturbed_gene_name'].drop_duplicates().to_list()
# define columns to replace
cols_to_replace = ['perturbed_target_ensg',	'perturbed_target_symbol',	'perturbed_target_biotype',	'perturbed_target_coord',	'perturbed_target_chromosome']
# define mapping dict for renaming columns in gene_ont for replacement
gene_ont_col_mapping = {
    'ensembl_gene_id':'perturbed_target_ensg',
    'gene_symbol':'perturbed_target_symbol',
    'biotype':'perturbed_target_biotype',
    'gene_coord':'perturbed_target_coord',
    'chromosome_name':'perturbed_target_chromosome'
}
# loop through genes and fill in the missing cols
for replacement_gene in genes_to_replace:
    if replacement_gene in cur_data.gene_ont['synonym'].values:
        # subset gene_ont and get values for replacement
        replacement = (
            cur_data.gene_ont.rename(columns=gene_ont_col_mapping)
            .loc[cur_data.gene_ont['synonym'].isin([replacement_gene]), cols_to_replace]
        )[cols_to_replace].values[0]
        # replace values in cur_data.adata.obs with the values from gene_ont
        cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isin([replacement_gene]), cols_to_replace] = replacement
        print(f"Replaced {replacement_gene} with {replacement}")
    else:
        print(f"No replacement found for {replacement_gene}")


No replacement found for nan
No replacement found for MTRNR2L4
No replacement found for LUZP6
Replaced SGK494 with ['ENSG00000167524' 'RSKR' 'protein_coding' 'chr17:28455752-28614197;-1'
 '17']
No replacement found for SMIM11B
No replacement found for AKAP2
No replacement found for MTRNR2L1
Replaced SEPT6 with ['ENSG00000125354' 'SEPTIN6' 'protein_coding'
 'chrX:119615724-119693949;-1' 'X']
No replacement found for FAM153B
No replacement found for OCLM
No replacement found for U2AF1L5
No replacement found for MTRNR2L8
No replacement found for CCL3L1


In [17]:
# replace non-mapped perturbed_target_symbol with original gene symbols
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_target_symbol'].isna(), 'perturbed_target_symbol'] = cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_target_symbol'].isna(), 'perturbed_gene_name'].values

In [18]:
# replace entries in perturbed_target_ensg that are not ENSEMBL ids with NA
cur_data.adata.obs.loc[(~cur_data.adata.obs['perturbed_target_ensg'].str.startswith('ENSG')) & (cur_data.adata.obs['perturbed_target_ensg'] != 'control_nontargeting'), 'perturbed_target_ensg'] = pd.NA

In [19]:
cur_data.adata.obs

,guide_group,perturbed_gene_id,total_counts,top_guide_UMI_counts,pct_counts_mt,lane_id,cell_barcode,perturbation_name,perturbed_gene_name,n_genes_by_counts,PuroR,guide_type,guide_sequence,low_quality,guide_id,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index
index,,,,,,,,,,,,,,,,,,,,,
0,targeting single sgRNA,ENSG00000198417,6484.0,25.0,0.200494,CD4i_R2L13,AAACAAGCAACAGAGGAAGTAGAG-1,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,MT1F,3108,2.621869,targeting,TGGAAAGTCCAGTCTCTCCT,False,MT1F-1,ENSG00000198417,MT1F,protein_coding,chr16:56657640-56660698;1,16,0
1,targeting single sgRNA,ENSG00000179922,37902.0,1318.0,0.477547,CD4i_R2L13,AAACAAGCAACAGAGGATCCCAAC-1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,ZNF784,6986,1.852205,targeting,TGGGATCGCGACTCCGGAGT,False,ZNF784-1,ENSG00000179922,ZNF784,protein_coding,chr19:55620741-55624566;-1,19,1
2,targeting single sgRNA,ENSG00000113068,7963.0,5.0,0.389301,CD4i_R2L13,AAACAAGCAACAGCACAAGTAGAG-1,AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13,PFDN1,3634,1.434438,targeting,CTTCAGCTCTAGATCCACGG,False,PFDN1-2,ENSG00000113068,PFDN1,protein_coding,chr5:140245035-140303113;-1,5,2
3,no sgRNA,nan,14945.0,NaN,1.124122,CD4i_R2L13,AAACAAGCAACCTCGCATCCCAAC-1,AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13,nan,5032,0.000000,NaN,NaN,False,NaN,<NA>,nan,NaN,NaN,NaN,3
4,no sgRNA,nan,13334.0,NaN,0.427479,CD4i_R2L13,AAACAAGCAACGACTAATCCCAAC-1,AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13,nan,5069,0.888736,NaN,NaN,False,NaN,<NA>,nan,NaN,NaN,NaN,4
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2154285,targeting single sgRNA,control_nontargeting,4652.0,3.0,0.795357,CD4i_R2L12,TTTGTGAGTTGTCCAGAGCTGTGA-1,TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12,control_nontargeting,2522,2.510375,non-targeting,TAGTCCTTAGGGTGGGCTGA,False,NTC-902,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,2154285
2154286,targeting single sgRNA,ENSG00000054654,19144.0,115.0,1.123067,CD4i_R2L12,TTTGTGAGTTGTGACTAAGTAGAG-1,TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12,SYNE2,5591,1.594534,targeting,TCCAGAGAGCCAGGCAAGCG,False,SYNE2-2,ENSG00000054654,SYNE2,protein_coding,chr14:63761899-64226433;1,14,2154286
2154287,targeting single sgRNA,ENSG00000215252,7138.0,78.0,0.448305,CD4i_R2L12,TTTGTGAGTTGTGACTACAGACCT-1,TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12,GOLGA8B,3462,2.532308,targeting,GCTTGAGAGCCCGCACGTAG,False,GOLGA8B-2,ENSG00000215252,GOLGA8B,protein_coding,chr15:34525095-34588503;-1,15,2154287


### Add `perturbed_target_number` column

In [20]:
# cur_data.count_entries(
#     slot='obs',
#     input_column='perturbed_target_ensg',
#     count_column_name='perturbed_target_number',
#     sep='|'
# )
cur_data.adata.obs['perturbed_target_number'] = 1

### Encode chromosomes as integers

In [21]:
cur_data.chromosome_encoding()

Chromosome encoding applied to perturbed_target_chromosome in adata.obs and stored as 'perturbed_target_chromosome_encoding'.


In [22]:
cur_data.adata.obs[['perturbation_name', 'perturbed_target_chromosome_encoding']]

,perturbation_name,perturbed_target_chromosome_encoding
index,,
0,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,16
1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,19
2,AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13,5
3,AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13,0
4,AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13,0
...,...,...
2154285,TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12,0
2154286,TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12,14
2154287,TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12,15


In [23]:
cur_data.adata.obs

,guide_group,perturbed_gene_id,total_counts,top_guide_UMI_counts,pct_counts_mt,lane_id,cell_barcode,perturbation_name,perturbed_gene_name,n_genes_by_counts,PuroR,guide_type,guide_sequence,low_quality,guide_id,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index,perturbed_target_number,perturbed_target_chromosome_encoding
index,,,,,,,,,,,,,,,,,,,,,,,
0,targeting single sgRNA,ENSG00000198417,6484.0,25.0,0.200494,CD4i_R2L13,AAACAAGCAACAGAGGAAGTAGAG-1,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,MT1F,3108,2.621869,targeting,TGGAAAGTCCAGTCTCTCCT,False,MT1F-1,ENSG00000198417,MT1F,protein_coding,chr16:56657640-56660698;1,16,0,1,16
1,targeting single sgRNA,ENSG00000179922,37902.0,1318.0,0.477547,CD4i_R2L13,AAACAAGCAACAGAGGATCCCAAC-1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,ZNF784,6986,1.852205,targeting,TGGGATCGCGACTCCGGAGT,False,ZNF784-1,ENSG00000179922,ZNF784,protein_coding,chr19:55620741-55624566;-1,19,1,1,19
2,targeting single sgRNA,ENSG00000113068,7963.0,5.0,0.389301,CD4i_R2L13,AAACAAGCAACAGCACAAGTAGAG-1,AAACAAGCAACAGCACAAGTAGAG-1_CD4i_R2L13,PFDN1,3634,1.434438,targeting,CTTCAGCTCTAGATCCACGG,False,PFDN1-2,ENSG00000113068,PFDN1,protein_coding,chr5:140245035-140303113;-1,5,2,1,5
3,no sgRNA,nan,14945.0,NaN,1.124122,CD4i_R2L13,AAACAAGCAACCTCGCATCCCAAC-1,AAACAAGCAACCTCGCATCCCAAC-1_CD4i_R2L13,nan,5032,0.000000,NaN,NaN,False,NaN,<NA>,nan,NaN,NaN,NaN,3,1,0
4,no sgRNA,nan,13334.0,NaN,0.427479,CD4i_R2L13,AAACAAGCAACGACTAATCCCAAC-1,AAACAAGCAACGACTAATCCCAAC-1_CD4i_R2L13,nan,5069,0.888736,NaN,NaN,False,NaN,<NA>,nan,NaN,NaN,NaN,4,1,0
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2154285,targeting single sgRNA,control_nontargeting,4652.0,3.0,0.795357,CD4i_R2L12,TTTGTGAGTTGTCCAGAGCTGTGA-1,TTTGTGAGTTGTCCAGAGCTGTGA-1_CD4i_R2L12,control_nontargeting,2522,2.510375,non-targeting,TAGTCCTTAGGGTGGGCTGA,False,NTC-902,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,control_nontargeting,2154285,1,0
2154286,targeting single sgRNA,ENSG00000054654,19144.0,115.0,1.123067,CD4i_R2L12,TTTGTGAGTTGTGACTAAGTAGAG-1,TTTGTGAGTTGTGACTAAGTAGAG-1_CD4i_R2L12,SYNE2,5591,1.594534,targeting,TCCAGAGAGCCAGGCAAGCG,False,SYNE2-2,ENSG00000054654,SYNE2,protein_coding,chr14:63761899-64226433;1,14,2154286,1,14
2154287,targeting single sgRNA,ENSG00000215252,7138.0,78.0,0.448305,CD4i_R2L12,TTTGTGAGTTGTGACTACAGACCT-1,TTTGTGAGTTGTGACTACAGACCT-1_CD4i_R2L12,GOLGA8B,3462,2.532308,targeting,GCTTGAGAGCCCGCACGTAG,False,GOLGA8B-2,ENSG00000215252,GOLGA8B,protein_coding,chr15:34525095-34588503;-1,15,2154287,1,15


### Curate replicates

In [24]:
cur_data.adata.obs = cur_data.adata.obs.rename(columns={'lane_id':'technical_replicate'})

### Add metadata

In [25]:
cur_data.create_columns(
    overwrite=True,
    slot="obs",
    col_dict={
        "dataset_id": cur_data.dataset_id,
        "sample_id": range(1, cur_data.adata.obs.shape[0] + 1),
        # perturbation type
        "perturbation_type_label": "CRISPRi",
        "perturbation_type_id": None,
        "data_modality": "Perturb-seq",
        "significant": None,
        "significance_criteria": None,
        "score_interpretation": None,

        # treatment
        "treatment_label": "untreated control",
        "treatment_id": "NCIT:C184729",
        # replicates
        # "technical_replicate": None,
        "biological_replicate": "D4_CE0006864",
        # model system
        "model_system_label": "primary_cell",
        "model_system_id": None,
        "tissue": "lymphoid tissue",
        "cell_line_label": None,
        "cell_line_id": None,
        "cell_type_label": "CD4-positive, alpha-beta T cell",
        "disease_label": "healthy",
        "disease_id": None,

        "timepoint": "P12DT8H0M0S",
        "species": "Homo sapiens",
        "sex_label": "male",
        "sex_id": None,
        "developmental_stage_label": "adult",
        "developmental_stage_id": None,

        "study_title": "Genome-scale perturb-seq in primary human CD4+ T cells maps context-specific regulators of T cell programs and human immune traits",
        "study_uri": "https://doi.org/10.64898/2025.12.23.696273",
        "study_year": 2025,
        "first_author": "Ronghui Zhu",
        "last_author": "Alexander Marson",

        "experiment_title": "Perturb-seq of primary human CD4-positive T cells for patient D4_CE0006864 under resting conditions",
        "experiment_summary": """
            Isolated human CD4-positive cells from four healthy donors were stimulated with ImmunoCult CD3/CD28/CD2 activator and sequentially transduced with dCas9-KRAB-Zim3 lentivirus (next morning after stimulation) and a Perturb-seq guide library (next afternoon after stimulation, MOI 0.2).
            The library consisted all genes expressed in human CD4+ T cells, all transcription factors annotated in the Lambert et al. (2018) and non-targeting controls totalling 12,748 genes.
            The gRNA sequences were selected from hCRISPRiv2 and Dolcetto libraries.
            On day 12, cells were split into three conditions:
            (1) Rest - cells were left for 8 hr without stimulation;
            (2) Stim8hr - cells were stimulated with ImmunoCult CD3/CD28/CD2 activator for 8 hr;
            (3) Stim48hr - cells were stimulated with ImmunoCult CD3/CD28/CD2 activator for 48 hr.
            Cells were harvested, fixed, stored using GEM-X Flex Sample Preparation v2 Kit and sequenced using GEM-X Flex Gene Expression Human n-plex kit converted into Ultima compatible libraries for sequencing on the Ultima Genomics UG100.
            """,

        "number_of_perturbed_targets": len(set(cur_data.adata.obs['perturbed_target_symbol'])),
        "number_of_perturbed_samples": cur_data.adata.obs.shape[0],

        "library_generation_type_id": "EFO:0022868",
        "library_generation_type_label": "endogenous",

        "library_generation_method_id": None,
        "library_generation_method_label": "dCas9-KRAB-Zim3",

        "enzyme_delivery_method_id": None,
        "enzyme_delivery_method_label": "lentivirus transduction",

        "library_delivery_method_id": None,
        "library_delivery_method_label": "lentivirus transduction",

        "enzyme_integration_state_id": None,
        "enzyme_integration_state_label": "random locus integration",

        "library_integration_state_id": None,
        "library_integration_state_label": "random locus integration",

        "enzyme_expression_control_id": None,
        "enzyme_expression_control_label": "constitutive transgene expression",

        "library_expression_control_id": None,
        "library_expression_control_label": "constitutive transgene expression",

        "library_name": "custom",
        "library_uri": None,

        "library_format_id": None,
        "library_format_label": "pooled",

        "library_scope_id": None,
        "library_scope_label": "focused",

        "library_perturbation_type_id": None,
        "library_perturbation_type_label": "inhibition",

        "library_manufacturer": "Marson lab",
        "library_lentiviral_generation": "2",
        "library_grnas_per_target": "2",
        "library_total_grnas": str(cur_data.adata.obs['guide_sequence'].str.split('|').explode().nunique()),
        "library_total_variants": None,

        "readout_dimensionality_id": None,
        "readout_dimensionality_label": "high-dimensional assay",

        "readout_type_id": None,
        "readout_type_label": "transcriptomic",

        "readout_technology_id": None,
        "readout_technology_label": "single-cell rna-seq",

        "method_name_id": None,
        "method_name_label": "Perturb-seq",

        "method_uri": None,

        "sequencing_library_kit_id": None,
        "sequencing_library_kit_label": "GEM-X Flex Gene Expression Human n-plex kit",

        "sequencing_platform_id": None,
        "sequencing_platform_label": "Ultima Genomics UG100",

        "sequencing_strategy_id": None,
        "sequencing_strategy_label": "barcode sequencing",

        "software_counts_id": None,
        "software_counts_label": "CellRanger",

        "software_analysis_id": None,
        "software_analysis_label": "scanpy",

        "reference_genome_id": None,
        "reference_genome_label": "GRCh38",

        "license_label": "MIT License",
        "license_id": "SWO:9000074",

        "associated_datasets": json.dumps([
            {
                "dataset_accession": "Primary Human CD4+ T Cell Perturb-seq",
                "dataset_uri": "s3://genome-scale-tcell-perturb-seq/marson2025_data/D4_Rest.assigned_guide.h5ad",
                "dataset_description": "Cell expression profiles for cells from donor D4_CE0006864 under resting conditions.",
                "dataset_file_name": "D4_Rest.assigned_guide.h5ad.h5ad",
            }
        ])
    }
)

Column dataset_id added to adata.obs
Column sample_id added to adata.obs
Column perturbation_type_label added to adata.obs
Column perturbation_type_id added to adata.obs
Column data_modality added to adata.obs
Column significant added to adata.obs
Column significance_criteria added to adata.obs
Column score_interpretation added to adata.obs
Column treatment_label added to adata.obs
Column treatment_id added to adata.obs
Column biological_replicate added to adata.obs
Column model_system_label added to adata.obs
Column model_system_id added to adata.obs
Column tissue added to adata.obs
Column cell_line_label added to adata.obs
Column cell_line_id added to adata.obs
Column cell_type_label added to adata.obs
Column disease_label added to adata.obs
Column disease_id added to adata.obs
Column timepoint added to adata.obs
Column species added to adata.obs
Column sex_label added to adata.obs
Column sex_id added to adata.obs
Column developmental_stage_label added to adata.obs
Column development

In [26]:
cur_data.adata.obs

,guide_group,perturbed_gene_id,total_counts,top_guide_UMI_counts,pct_counts_mt,technical_replicate,cell_barcode,perturbation_name,perturbed_gene_name,n_genes_by_counts,PuroR,guide_type,guide_sequence,low_quality,guide_id,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index,perturbed_target_number,perturbed_target_chromosome_encoding,dataset_id,sample_id,perturbation_type_label,perturbation_type_id,data_modality,significant,significance_criteria,score_interpretation,treatment_label,treatment_id,biological_replicate,model_system_label,model_system_id,tissue,cell_line_label,cell_line_id,cell_type_label,disease_label,disease_id,timepoint,species,sex_label,sex_id,developmental_stage_label,developmental_stage_id,study_title,study_uri,study_year,first_author,last_author,experiment_title,experiment_summary,number_of_perturbed_targets,number_of_perturbed_samples,library_generation_type_id,library_generation_type_label,library_generation_method_id,library_generation_method_label,enzyme_delivery_method_id,enzyme_delivery_method_label,library_delivery_method_id,library_delivery_method_label,enzyme_integration_state_id,enzyme_integration_state_label,library_integration_state_id,library_integration_state_label,enzyme_expression_control_id,enzyme_expression_control_label,library_expression_control_id,library_expression_control_label,library_name,library_uri,library_format_id,library_format_label,library_scope_id,library_scope_label,library_perturbation_type_id,library_perturbation_type_label,library_manufacturer,library_lentiviral_generation,library_grnas_per_target,library_total_grnas,library_total_variants,readout_dimensionality_id,readout_dimensionality_label,readout_type_id,readout_type_label,readout_technology_id,readout_technology_label,method_name_id,method_name_label,method_uri,sequencing_library_kit_id,sequencing_library_kit_label,sequencing_platform_id,sequencing_platform_label,sequencing_strategy_id,sequencing_strategy_label,software_counts_id,software_counts_label,software_analysis_id,software_analysis_label,reference_genome_id,reference_genome_label,license_label,license_id,associated_datasets
index,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,
0,targeting single sgRNA,ENSG00000198417,6484.0,25.0,0.200494,CD4i_R2L13,AAACAAGCAACAGAGGAAGTAGAG-1,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,MT1F,3108,2.621869,targeting,TGGAAAGTCCAGTCTCTCCT,False,MT1F-1,ENSG00000198417,MT1F,protein_coding,chr16:56657640-56660698;1,16,0,1,16,zhu_2025_D4_rest_cl,1,CRISPRi,None,Perturb-seq,None,None,None,untreated control,NCIT:C184729,D4_CE0006864,primary_cell,None,lymphoid tissue,None,None,"CD4-positive, alpha-beta T cell",healthy,None,P12DT8H0M0S,Homo sapiens,male,None,adult,None,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq of primary human CD4-positive T ce...,\n Isolated human CD4-positive cell...,12417,2154290,EFO:0022868,endogenous,None,dCas9-KRAB-Zim3,None,lentivirus transduction,None,lentivirus transduction,None,random locus integration,None,random locus integration,None,constitutive transgene expression,None,constitutive transgene expression,custom,None,None,pooled,None,focused,None,inhibition,Marson lab,2,2,24708,None,None,high-dimensional assay,None,transcriptomic,None,single-cell rna-seq,None,Perturb-seq,None,None,GEM-X Flex Gene Expression Human n-plex kit,None,Ultima Genomics UG100,None,barcode sequencing,None,CellRanger,None,scanpy,None,GRCh38,MIT License,SWO:9000074,"[{""dataset_accession"": ""Primary Human CD4+ T C..."
1,targeting single sgRNA,ENSG00000179922,37902.0,1318.0,0.477547,CD4i_R2L13,AAACAAGCAACAGAGGATCCCAAC-1,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,ZNF784,6986,1.852205,targeting,TGGGATCGCGACTCCGGAGT,False,ZNF784-1,ENSG00000179922,ZNF784,protein_coding,chr19:55620741-55624566;-1,19,1,1,19,zhu_2025_

### Curate tissue information


In [27]:
cur_data.standardize_ontology(
    input_column='tissue',
    column_type='term_name',
    ontology_type='tissue',
    overwrite=True
)

Mapped 1 tissue ontology terms from `tissue` column to ontology terms
DataFrame shape: (1, 4)
--------------------------------------------------
      input_column input_column_lower       name_lower     ontology_id
0  lymphoid tissue    lymphoid tissue  lymphoid tissue  UBERON:0001744
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


### Curate cell type information

In [28]:
cur_data.standardize_ontology(
    input_column='cell_type_label',
    column_type='term_name',
    ontology_type='cell_type',
    overwrite=True
)

Mapped 1 cell_type ontology terms from `cell_type_label` column to ontology terms
DataFrame shape: (1, 4)
--------------------------------------------------
                      input_column               input_column_lower  \
0  CD4-positive, alpha-beta T cell  cd4-positive, alpha-beta t cell   

                        name_lower ontology_id  
0  cd4-positive, alpha-beta t cell  CL:0000624  
--------------------------------------------------
Overwriting column cell_type_label in adata.obs


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


### Curate disease information

In [29]:
cur_data.standardize_ontology(
    input_column='disease_label',
    column_type='term_name',
    ontology_type='disease',
    overwrite=True
)

### Match schema column order

In [30]:
cur_data.match_schema_columns(slot='obs')

Matched columns of adata.obs to the obs_schema.


### Validate obs metadata

In [31]:
cur_data.validate_data(slot='obs', verbose=True)

2026-02-17 16:58:04,412 INFO curation_tools.curation_tools: adata.obs is valid according to the obs_schema.


,dataset_id,sample_id,data_modality,significant,significance_criteria,perturbation_name,perturbed_target_coord,perturbed_target_chromosome,perturbed_target_chromosome_encoding,perturbed_target_number,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,guide_sequence,perturbation_type_label,perturbation_type_id,timepoint,treatment_label,treatment_id,technical_replicate,biological_replicate,model_system_label,model_system_id,species,tissue_label,tissue_id,cell_type_label,cell_type_id,cell_line_label,cell_line_id,sex_label,sex_id,developmental_stage_label,developmental_stage_id,disease_label,disease_id,study_title,study_uri,study_year,first_author,last_author,experiment_title,experiment_summary,number_of_perturbed_targets,number_of_perturbed_samples,library_generation_type_id,library_generation_type_label,library_generation_method_id,library_generation_method_label,enzyme_delivery_method_id,enzyme_delivery_method_label,library_delivery_method_id,library_delivery_method_label,enzyme_integration_state_id,enzyme_integration_state_label,library_integration_state_id,library_integration_state_label,enzyme_expression_control_id,enzyme_expression_control_label,library_expression_control_id,library_expression_control_label,library_name,library_uri,library_format_id,library_format_label,library_scope_id,library_scope_label,library_perturbation_type_id,library_perturbation_type_label,library_manufacturer,library_lentiviral_generation,library_grnas_per_target,library_total_grnas,library_total_variants,readout_dimensionality_id,readout_dimensionality_label,readout_type_id,readout_type_label,readout_technology_id,readout_technology_label,method_name_id,method_name_label,method_uri,sequencing_library_kit_id,sequencing_library_kit_label,sequencing_platform_id,sequencing_platform_label,sequencing_strategy_id,sequencing_strategy_label,software_counts_id,software_counts_label,software_analysis_id,software_analysis_label,score_interpretation,reference_genome_id,reference_genome_label,associated_datasets,license_label,license_id
0,zhu_2025_D4_rest_cl,1,Perturb-seq,<NA>,<NA>,AAACAAGCAACAGAGGAAGTAGAG-1_CD4i_R2L13,chr16:56657640-56660698;1,16,16,1,ENSG00000198417,MT1F,protein_coding,TGGAAAGTCCAGTCTCTCCT,CRISPRi,<NA>,P12DT8H0M0S,untreated control,NCIT:C184729,CD4i_R2L13,D4_CE0006864,primary_cell,<NA>,Homo sapiens,lymphoid tissue,UBERON:0001744,"CD4-positive, alpha-beta T cell",CL:0000624,<NA>,<NA>,male,<NA>,adult,<NA>,healthy,<NA>,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq of primary human CD4-positive T ce...,\n Isolated human CD4-positive cell...,12417,2154290,EFO:0022868,endogenous,<NA>,dCas9-KRAB-Zim3,<NA>,lentivirus transduction,<NA>,lentivirus transduction,<NA>,random locus integration,<NA>,random locus integration,<NA>,constitutive transgene expression,<NA>,constitutive transgene expression,custom,<NA>,<NA>,pooled,<NA>,focused,<NA>,inhibition,Marson lab,2,2,24708,<NA>,<NA>,high-dimensional assay,<NA>,transcriptomic,<NA>,single-cell rna-seq,<NA>,Perturb-seq,<NA>,<NA>,GEM-X Flex Gene Expression Human n-plex kit,<NA>,Ultima Genomics UG100,<NA>,barcode sequencing,<NA>,CellRanger,<NA>,scanpy,<NA>,<NA>,GRCh38,"[{""dataset_accession"": ""Primary Human CD4+ T C...",MIT License,SWO:9000074
1,zhu_2025_D4_rest_cl,2,Perturb-seq,<NA>,<NA>,AAACAAGCAACAGAGGATCCCAAC-1_CD4i_R2L13,chr19:55620741-55624566;-1,19,19,1,ENSG00000179922,ZNF784,protein_coding,TGGGATCGCGACTCCGGAGT,CRISPRi,<NA>,P12DT8H0M0S,untreated control,NCIT:C184729,CD4i_R2L13,D4_CE0006864,primary_cell,<NA>,Homo sapiens,lymphoid tissue,UBERON:0001744,"CD4-positive, alpha-beta T cell",CL:0000624,<NA>,<NA>,male,<NA>,adult,<NA>,healthy,<NA>,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq of primary human CD4-positive T ce...,\n Isolated human CD4-positive cell...,12417,2154290,EFO:0022868,endogenous,<NA>

# VAR slot curation

### Standardise genes

In [32]:
cur_data.adata.var

,gene_ids,feature_types,genome,gene_name,mt
CUSTOM001_PuroR,CUSTOM001_PuroR,Gene Expression,GRCh38,PuroR,False
ENSG00000000003,ENSG00000000003,Gene Expression,GRCh38,TSPAN6,False
ENSG00000000005,ENSG00000000005,Gene Expression,GRCh38,TNMD,False
ENSG00000000419,ENSG00000000419,Gene Expression,GRCh38,DPM1,False
ENSG00000000457,ENSG00000000457,Gene Expression,GRCh38,SCYL3,False
...,...,...,...,...,...
ENSG00000291110,ENSG00000291110,Gene Expression,GRCh38,TRIM16L,False
ENSG00000291122,ENSG00000291122,Gene Expression,GRCh38,CASTOR3P,False
ENSG00000291135,ENSG00000291135,Gene Expression,GRCh38,FCGR1BP,False
ENSG00000291145,ENSG00000291145,Gene Expression,GRCh38,PPP5D1P,False


In [36]:
cur_data.standardize_genes(
    slot="var",
    input_column="gene_ids",
    input_column_type="ensembl_gene_id",
    remove_version=False,
    multiple_entries=False
)

Missing Ensembl IDs: ['ENSG00000148362', 'CUSTOM001_PuroR', 'ENSG00000139656']; attempting to fetch latest IDs...
Fetched latest Ensembl IDs: {'ENSG00000148362': 'ENSG00000310560', 'ENSG00000139656': 'ENSG00000226519'}
--------------------------------------------------
Successfully mapped 18130 out of 18130 Ensembl IDs.
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


In [37]:
# replace gene symbols that are NOT ENSG with original provided gene symbol
cur_data.adata.var.loc[(cur_data.adata.var['gene_symbol'].isna()) &
 (~cur_data.adata.var['gene_name'].str.startswith('ENSG')), 'gene_symbol'] = cur_data.adata.var.loc[(cur_data.adata.var['gene_symbol'].isna()) &
 (~cur_data.adata.var['gene_name'].str.startswith('ENSG')), 'gene_name']

In [38]:
cur_data.adata.var.loc[cur_data.adata.var['ensembl_gene_id'] == 'CUSTOM001_PuroR', 'ensembl_gene_id'] = None

### Validate var metadata

In [39]:
cur_data.validate_data(slot='var')

2026-02-17 17:01:33,546 INFO curation_tools.curation_tools: adata.var is valid according to the var_schema.


,ensembl_gene_id,gene_symbol
index,,
0,None,PuroR
1,ENSG00000000003,TSPAN6
2,ENSG00000000005,TNMD
3,ENSG00000000419,DPM1
4,ENSG00000000457,SCYL3
...,...,...
18125,ENSG00000291110,TRIM16L
18126,ENSG00000291122,CASTOR3P
18127,ENSG00000291135,FCGR1BP


# Save the dataset

In [40]:
cur_data.save_curated_data_h5ad()

/nfs/production/mfreeberg/perturb-seq/aleks/PerturbationCatalogue/data_exploration/curation_tools/curation_tools.py:327: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  adata.obs = adata.obs.fillna(value=np.nan)
... storing 'dataset_id' as categorical
... storing 'data_modality' as categorical
... storing 'significance_criteria' as categorical
... storing 'perturbed_target_coord' as categorical
... storing 'perturbed_target_chromosome' as categorical
... storing 'perturbed_target_ensg' as categorical
... storing 'perturbed_target_symbol' as categorical
... storing 'perturbed_target_biotype' as categorical
... storing 'guide_sequence' as categorical
... storing 'perturbation_type_label' as categorical
... storing 'perturbation_type_id' as categorical
... storing 'timepoint

✅ Curated h5ad data saved to ../curated/h5ad/zhu_2025_D4_rest_cl_curated.h5ad


In [41]:
cur_data.save_curated_data_parquet(split_metadata=True, save_metadata_only=True)

✅ Metadata saved to ../curated/parquet/zhu_2025_D4_rest_cl_curated_metadata.parquet


# Upload to BigQuery

In [ ]:
# upload_parquet_to_bq(
#     parquet_path='../curated/parquet/zhu_2025_D4_rest_cl_curated_metadata.parquet',
#     bq_dataset_id='prj-ext-dev-pertcat-437314.perturb_seq',
#     bq_table_name='metadata',
#     key_columns=['dataset_id', 'sample_id'],
#     verbose=True
# )

# Upload to GC Storage

In [ ]:
# !gcloud storage cp ../curated/h5ad/zhu_2025_D4_rest_cl_curated.h5ad gs://perturbation-catalogue-lake/perturbseq/curated/